In [1]:
import numpy as np 
import pandas as pd

In [2]:
df=pd.read_csv('youtube_comments_cleaned3.csv')
df.head()

,CommentID,VideoID,VideoTitle,AuthorName,AuthorChannelID,CommentText,Sentiment,Likes,Replies,PublishedAt,CountryCode,CategoryID
0,UgyRjrEdJIPrf68uND14AaABAg,mcY4M9gjtsI,They killed my friend.#tales #movie #shorts,@OneWhoWandered,UC_-UEXaBL1dqqUPGkDll49A,Anyone know what movie this is?,Neutral,0,2,2025-01-15 00:54:55,NZ,1
1,UgxXxEIySAwnMNw8D7N4AaABAg,2vuXcw9SZbA,Man Utd conceding first penalty at home in yea...,@chiefvon3068,UCZ1LcZESjYqzaQRhjdZJFwg,The fact they're holding each other back while...,Positive,0,0,2025-01-13 23:51:46,AU,17
2,UgxB0jh2Ur41mcXr5IB4AaABAg,papg2tsoFzg,Welcome to Javascript Course,@Abdulla-ip8qr,UCWBK35w5Swy1iF5xIbEyw3A,waiting next video will be?,Neutral,1,0,2020-07-06 13:18:16,IN,27
3,UgwMOh95MfK0GuXLLrF4AaABAg,31KTdfRH6nY,Building web applications in Java with Spring ...,@finnianthehuman,UCwQ2Z03nOcMxWozBb_Cv66w,Thanks for the great video.\n\nI don't underst...,Neutral,0,1,2024-09-18 12:04:12,US,27
4,UgxJuUe5ysG8OSbABAl4AaABAg,-hV6aeyPHPA,After a new engine her car dies on her way hom...,@ryoutubeplaylistb6137,UCTTcJ0tsAKQokmHB2qVb1qQ,Good person helping good people.\nThis is how ...,Positive,3,1,2025-01-10 19:39:03,US,2


In [3]:
df['CommentText'].iloc[90]

"The LeetCode instructions were absolutely awful for this question. They rarely seem to explain stuff in simple terms, it's so annoying. Half the battle is deciphering the question itself, sometimes the code isn't even hard to come up with, just interpreting the question."

In [4]:
from sklearn.model_selection import train_test_split
model_df=df[['CommentText','Sentiment']].dropna().copy()

In [5]:
model_df['CommentText']=model_df['CommentText'].str.strip()
model_df = model_df[
    model_df["CommentText"].ne("")
].copy()

# Check sentiment distribution
print("Dataset shape:", model_df.shape)
print(model_df["Sentiment"].value_counts())
print(model_df["Sentiment"].value_counts(normalize=True).round(3))

Dataset shape: (989258, 2)
Sentiment
Negative    339255
Neutral     326104
Positive    323899
Name: count, dtype: int64
Sentiment
Negative    0.343
Neutral     0.330
Positive    0.327
Name: proportion, dtype: float64


In [6]:
X=model_df['CommentText']
y=model_df['Sentiment']

X_train,X_test,y_train,y_test=train_test_split(
    X,y,
    test_size=0.2,
    random_state=42,
    stratify=y
    )

print("Train shape:", X_train.shape)
print("Test shape:", X_test.shape)

Train shape: (791406,)
Test shape: (197852,)


In [11]:
from sklearn.pipeline import Pipeline
from sklearn.feature_extraction.text import TfidfVectorizer
from sklearn.linear_model import LogisticRegression
import time

from sklearn.pipeline import Pipeline
from sklearn.feature_extraction.text import TfidfVectorizer
from sklearn.naive_bayes import MultinomialNB
from sklearn.linear_model import LogisticRegression, SGDClassifier
from sklearn.svm import LinearSVC

model=Pipeline([
    ('tfidf',TfidfVectorizer(
        max_features=100_000,
        ngram_range=(1,2),
        min_df=2,
        sublinear_tf=True,
        dtype="float32"
    )),
    ('classifier',LogisticRegression(max_iter=100))
])
model.fit(X_train, y_train)

c:\Users\omkar\anaconda3\Lib\site-packages\sklearn\linear_model\_logistic.py:599: ConvergenceWarning: lbfgs failed to converge after 100 iteration(s) (status=1):
STOP: TOTAL NO. OF ITERATIONS REACHED LIMIT

Increase the number of iterations to improve the convergence (max_iter=100).
You might also want to scale the data as shown in:
    https://scikit-learn.org/stable/modules/preprocessing.html
Please also refer to the documentation for alternative solver options:
    https://scikit-learn.org/stable/modules/linear_model.html#logistic-regression
  n_iter_i = _check_optimize_result(


,"steps steps: list of tuplesList of (name of step, estimator) tuples that are to be chained insequential order. To be compatible with the scikit-learn API, all stepsmust define `fit`. All non-last steps must also define `transform`. See:ref:`Combining Estimators <combining_estimators>` for more details.","[('tfidf', ...), ('classifier', ...)]"
,"transform_input transform_input: list of str, default=NoneThe names of the :term:`metadata` parameters that should be transformed by thepipeline before passing it to the step consuming it.This enables transforming some input arguments to ``fit`` (other than ``X``)to be transformed by the steps of the pipeline up to the step which requiresthem. Requirement is defined via :ref:`metadata routing <metadata_routing>`.For instance, this can be used to pass a validation set through the pipeline.You can only set this if metadata routing is enabled, which youcan enable using ``sklearn.set_config(enable_metadata_routing=True)``... versionadded:: 1.6",None
,"memory memory: str or object with the joblib.Memory interface, default=NoneUsed to cache the fitted transformers of the pipeline. The last stepwill never be cached, even if it is a transformer. By default, nocaching is performed. If a string is given, it is the path to thecaching directory. Enabling caching triggers a clone of the transformersbefore fitting. Therefore, the transformer instance given to thepipeline cannot be inspected directly. Use the attribute ``named_steps``or ``steps`` to inspect estimators within the pipeline. Caching thetransformers is advantageous when fitting is time consuming. See:ref:`sphx_glr_auto_examples_neighbors_plot_caching_nearest_neighbors.py`for an example on how to enable caching.",None
,"verbose verbose: bool, default=FalseIf True, the time elapsed while fitting each step will be printed as itis completed.",False
Name,Type,Value
"classes_ classes_: ndarray of shape (n_classes,)The classes labels. Only exist if the last step of the pipeline is aclassifier.","ndarray[object](3,)","['Negative','Neutral','Positive']"
,"ngram_range ngram_range: tuple (min_n, max_n), default=(1, 1)The lower and upper boundary of the range of n-values for differentn-grams to be extracted. All values of n such that min_n <= n <= max_nwill be used. For example an ``ngram_range`` of ``(1, 1)`` means onlyunigrams, ``(1, 2)`` means unigrams and bigrams, and ``(2, 2)`` meansonly bigrams.Only applies if ``analyzer`` is not callable.","(1, ...)"
,"min_df min_df: float or int, default=1When building the vocabulary ignore terms that have a documentfrequency strictly lower than the given threshold. This value is alsocalled cut-off in the literature.If float in range of [0.0, 1.0], the parameter represents a proportionof documents, integer absolute counts.This parameter is ignored if vocabulary is not None.",2
,"max_features max_features: int, default=NoneIf not None, build a vocabulary that only consider the top`max_features` ordered by term frequency across the corpus.Otherwise, all features are used.This parameter is ignored if vocabulary is not None.",100000
,"dtype dtype: dtype, default=float64Type of the matrix returned by fit_transform() or transform().",'float32'
,"sublinear_tf sublinear_tf: bool, default=FalseApply sublinear tf scaling, i.e. replace tf with 1 + log(tf).",True


In [12]:
from sklearn.metrics import accuracy_score, classification_report
y_pred=model.predict(X_test)
print("accuracy:",accuracy_score(y_test,y_pred))
print(classification_report(y_test,y_pred))

accuracy: 0.6981784364070113
              precision    recall  f1-score   support

    Negative       0.70      0.71      0.70     67851
     Neutral       0.64      0.67      0.65     65221
    Positive       0.76      0.72      0.74     64780

    accuracy                           0.70    197852
   macro avg       0.70      0.70      0.70    197852
weighted avg       0.70      0.70      0.70    197852



In [ ]:
import numpy as np

from sklearn.pipeline import Pipeline
from sklearn.feature_extraction.text import TfidfVectorizer
from sklearn.linear_model import LogisticRegression
from sklearn.model_selection import GridSearchCV, StratifiedKFold
from sklearn.metrics import accuracy_score, f1_score, classification_report

pipeline=Pipeline([
    ('tfidf',TfidfVectorizer(
                max_features=100_000,
        ngram_range=(1, 2),
        min_df=2,
        sublinear_tf=True,
        dtype=np.float32
    )),
    ("classifier", LogisticRegression(
        max_iter=2000,
        solver="lbfgs",
        random_state=42
    ))
    ])

param_grid={
    'tfidf__max_features':[50_000, 100_000],
    'tfidf__ngram_range':[(1, 1), (1, 2)],
    'classifier__C':[0.1, 0.5, 1,2,5,10],
    "classifier__class_weight": [None, "balanced"]
}

cv = StratifiedKFold(
    n_splits=3,
    shuffle=True,
    random_state=42
)

grid = GridSearchCV(
    pipeline,
    param_grid,
    scoring="f1_macro",
    cv=cv,
    n_jobs=-1,
    verbose=2
)


grid.fit(X_train, y_train)

best_model=grid.best_estimator_

best_params=grid.best_params_
best_score=grid.best_score_
predictions = best_model.predict(X_test)

print("accuracy:", accuracy_score(y_test, predictions))

print("Best Parameters:", best_params)
print("Macro F1:", f1_score(y_test, predictions, average="macro"))
print(classification_report(y_test, predictions))


Fitting 3 folds for each of 48 candidates, totalling 144 fits


In [ ]:
# using nlp transformers for sentiment analysis

%pip install -U transformers torch accelerate scikit-learn pandas tqdm

^C
Note: you may need to restart the kernel to use updated packages.


In [ ]:
# import torch
# from transformers import pipeline

# MODEL_NAME = "cardiffnlp/twitter-roberta-base-sentiment-latest"

# device = 0 if torch.cuda.is_available() else -1

# sentiment_model = pipeline(
#     task="text-classification",
#     model=MODEL_NAME,
#     tokenizer=MODEL_NAME,
#     device=device
# )

# print("Model loaded successfully!")
# print("Device:", "GPU" if device == 0 else "CPU")

ModuleNotFoundError: No module named 'torch'

In [ ]:
# comments = [
#     "This video is amazing, I really enjoyed it!",
#     "The video is okay, nothing special.",
#     "This is terrible and completely boring.",
#     "I don't like this video at all."
# ]

# predictions = sentiment_model(
#     comments,
#     batch_size=4,
#     truncation=True
# )

# for comment, result in zip(comments, predictions):
#     print("Comment:", comment)
#     print("Sentiment:", result["label"])
#     print("Confidence:", round(result["score"], 4))
#     print("-" * 60)

In [ ]:
# from sklearn.model_selection import train_test_split
# from sklearn.metrics import (
#     accuracy_score,
#     precision_score,
#     recall_score,
#     f1_score,
#     classification_report,
#     confusion_matrix
# )

# # Select a representative test sample
# eval_size = min(5000, len(X_test))

# X_hf_eval, _, y_hf_eval, _ = train_test_split(
#     X_test,
#     y_test,
#     train_size=eval_size,
#     random_state=42,
#     stratify=y_test
# )

# # Run predictions in batches
# hf_results = sentiment_model(
#     X_hf_eval.tolist(),
#     batch_size=16,
#     truncation=True
# )

# hf_predictions = [r["label"].title() for r in hf_results]

# # Normalize actual labels
# y_actual = y_hf_eval.astype(str).str.strip().str.title()

# print(classification_report(
#     y_actual,
#     hf_predictions,
#     labels=["Negative", "Neutral", "Positive"],
#     zero_division=0
# ))

# print("Accuracy:", accuracy_score(y_actual, hf_predictions))
# print("Macro F1:", f1_score(
#     y_actual, hf_predictions, average="macro", zero_division=0
# ))